In [0]:
# Criando o banco de dados da camada Silver
spark.sql("CREATE DATABASE IF NOT EXISTS silver")

DataFrame[]

In [0]:
from pyspark.sql.functions import col, trim, upper, regexp_replace, when, coalesce, year, row_number, expr
from pyspark.sql.window import Window

# Lê os dados brutos da camada Bronze
df_info = spark.read.table("bronze.tb_movies_info")

# 1. Renomear as colunas para o português
df_info = df_info.withColumnRenamed("id", "id_filme") \
                 .withColumnRenamed("title", "titulo") \
                 .withColumnRenamed("original_title", "titulo_original") \
                 .withColumnRenamed("release_date", "data_lancamento") \
                 .withColumnRenamed("runtime", "duracao_minutos") \
                 .withColumnRenamed("original_language", "idioma_original") \
                 .withColumnRenamed("status", "status_filme") \
                 .withColumnRenamed("overview", "sinopse") \
                 .withColumnRenamed("tagline", "frase_divulgacao")

# 2. Limpeza e Tradução do Status
# Normaliza: troca hífens/underlines por espaço e padroniza para letras maiúsculas
df_info = df_info.withColumn("status_filme", upper(trim(regexp_replace(col("status_filme"), r"[-_\s]+", " "))))

# Aplica a tradução. O que for corrompido vira "Não Informado"
df_info = df_info.withColumn("status_filme", 
    when(col("status_filme") == "RELEASED", "Lançado")
    .when(col("status_filme").isin("POST PRODUCTION", "POSTPRODUCTION"), "Pós-Produção")
    .when(col("status_filme").isin("IN PRODUCTION", "INPRODUCTION"), "Em Produção")
    .when(col("status_filme") == "PLANNED", "Planejado")
    .when(col("status_filme") == "RUMORED", "Rumores")
    .when(col("status_filme").isin("CANCELED", "CANCELLED"), "Cancelado")
    .otherwise("Não Informado")
)

# 3. Tratamento de Data Multi-Formato 
df_info = df_info.withColumn("data_lancamento", 
    coalesce(
        expr("try_to_date(data_lancamento, 'yyyy-MM-dd')"),
        expr("try_to_date(data_lancamento, 'MM-dd-yyyy')"),  
        expr("try_to_date(data_lancamento, 'dd/MM/yyyy')"),
        expr("try_to_date(data_lancamento, 'MM/dd/yyyy')")
    )
)
# Deriva o ano de lançamento
df_info = df_info.withColumn("ano_lancamento", year(col("data_lancamento")))

# ---> AQUI ENTRA A GARANTIA DE TIPAGEM (id_filme como STRING e duracao_minutos como INT válido) <---
df_info = df_info.withColumn("id_filme", trim(col("id_filme").cast("string"))) \
                 .withColumn("duracao_minutos", expr("try_cast(duracao_minutos as int)")) \
                 .withColumn("duracao_minutos", when(col("duracao_minutos") <= 0, None).otherwise(col("duracao_minutos")))

# 4. Deduplicação por Filme e Seleção das Colunas Finais
# Agrupa por id_filme, ordena pela data de ingestão mais recente e seleciona apenas as colunas do mapeamento
window_spec = Window.partitionBy("id_filme").orderBy(col("ingestion_datetime").desc())
df_info = df_info.withColumn("num_linha", row_number().over(window_spec)) \
                 .filter(col("num_linha") == 1) \
                 .select(
                     "id_filme", "titulo", "titulo_original", "data_lancamento", "ano_lancamento",
                     "duracao_minutos", "idioma_original", "status_filme", "sinopse", "frase_divulgacao"
                 )

# 5. Salva na camada Silver sobrescrevendo também a estrutura antiga (overwriteSchema)
df_info.write.format("delta") \
       .mode("overwrite") \
       .option("overwriteSchema", "true") \
       .saveAsTable("silver.tb_info_filmes")

print("Tabela silver.tb_info_filmes criada com sucesso!")
display(df_info)

Tabela silver.tb_info_filmes criada com sucesso!


id_filme,titulo,titulo_original,data_lancamento,ano_lancamento,duracao_minutos,idioma_original,status_filme,sinopse,frase_divulgacao
1000004,Purple Beatz,Purple Beatz,2022-07-07,2022,86,en,Lançado,"Sarah-Jane is a young aspiring jazz singer from Bournemouth who moves to London to embark on a music career. Not long in town, she falls for the handsome Airbeats, but also sinister music producer Russell-D, who represents a darker side to the music industry.",A drum n bass romance.
1000005,Aisha Brown: The First Black Woman Ever,Aisha Brown: The First Black Woman Ever,2020-02-14,2020,42,en,Lançado,"No one, and nothing, is off-limits for comedian Aisha Brown, as she takes on her boyfriend’s penis, racism, clinical depression, and Donald Trump, in this hilarious one-hour comedy special from Just For Laughs.",null
1000007,KYLE BROWNRIGG: INTRODUCING LYLE,Kyle Brownrigg: Introducing Lyle,2022-05-27,2022,36,en,Lançado,"Kyle Brownrigg takes the stage in this hilarious half-hour stand-up special where he laments gender reveal parties, talks about his Irish boyfriend, and introduces the world to his drunk persona, Lyle.",null
1000011,Worth Your Weight in Gold,O Teu Peso Em Ouro,2022-07-14,2022,26,pt,Lançado,"Oscar, a renowned hypnotherapist, uses the last moments in his hotel room to say goodbye to the vertiginous Mercedes and rid old Norberto of his bitterness.",null
1000014,On va manquer !,On va manquer !,2018-05-15,2018,null,fr,Lançado,null,null
1000030,58 Hours: The Baby Jessica Story,58 Hours: The Baby Jessica Story,2021-07-31,2021,null,es,Lançado,null,null
1000054,One Hundred Years and Hope,百年と希望,2022-06-18,2022,107,ja,Lançado,"In a country ruled by the Liberal Democratic Party, running on austerity and neoliberal ambitions, for most of its postwar years, gender and economic inequalities have become increasingly acute in Japan. Takashi Nishihara, a filmmaker who has been following the youth protests in Japan notices that there is one party that seems to be raising issues of gender and economic in the political sphere, the Japanese Communist Party (JCP), a party about to enter its hundredth year and consistently burdened by its historical connotations. Though an outsider of the party, Nishihara gained unprecedented access to the JCP and driven by his interest in the younger party members who find hope in the JCP, the resulting documentary goes beyond party politics and observes the current grassroots leftist movements in Japan. It also becomes witness to the larger and deep-seated patriarchal system that continues to quell momentums of hope.",null
1000058,Homecoming,Le retour,2023-07-12,2023,110,fr,Lançado,"Kheìdidja, in her forties, works for a wealthy Parisian family who offers her the opportunity to take care of their children for a summer in Corsica. It's an opportunity for her to return with her daughters, Jessica and Farah, to the island they left fifteen years earlier in tragic circumstances.",null
1000059,素敵な選TAXI SPECIAL〜湯けむり連続選択肢〜,素敵な選TAXI SPECIAL〜湯けむり連続選択肢〜,2016-04-05,2016,116,ja,Lançado,"Edawakare, the driver of the Time Taxi that allows passengers to return to their life's turning points, visits a hot spring this time around. An array of guests at the inn are fraught with troubles in their life and become passengers of the Time Taxi. And somehow all the clients are actually part of a bigger picture?!",null
1000073,A Chance To Win,Pour l'honneur,2023-05-03,2023,97,fr,Lançado,"Two villages in the south of France have always been bitter rivals, but when a group of asylum seekers arrive in the community, the life of both villages is shaken up and age-old disagreements escalate. Their antagonism reaches its peak with the annual rugby derby played between the two village teams, but this time, with the new outsiders joining as unexpected recruits, the result of the 100th match will be more unpredictable than ever.",null


In [0]:
from pyspark.sql.functions import col, when, regexp_replace, trim, lit, round, row_number
from pyspark.sql.types import DecimalType
from pyspark.sql.window import Window

# 1. Obter a cotação mais recente do dólar da tabela Bronze
df_cotacao = spark.read.table("bronze.tb_cotacao_dolar")
taxa_dolar = df_cotacao.orderBy(col("dataHoraCotacao").desc()).select("cotacaoCompra").first()[0]

# 2. Ler os dados financeiros brutos
df_fin = spark.read.table("bronze.tb_movies_financials")

# Renomear as colunas originais e padronizar id_filme como texto (STRING)
df_fin = df_fin.withColumnRenamed("id", "id_filme") \
               .withColumnRenamed("budget", "orcamento_usd") \
               .withColumnRenamed("revenue", "receita_usd") \
               .withColumn("id_filme", trim(col("id_filme").cast("string")))

# 3. Limpeza, Higienização e Validação das Métricas Financeiras
for coluna in ["orcamento_usd", "receita_usd"]:
    # Regra A: Tratar valores textuais de ausência como nulos ANTES da conversão
    df_fin = df_fin.withColumn(coluna, 
        when(trim(col(coluna)).isin("Unknown", "Não Informado", "N/A", ""), None)
        .otherwise(col(coluna))
    )
    # Regra B: Higienizar colunas para remover moedas e separadores de milhar
    df_fin = df_fin.withColumn(coluna, regexp_replace(col(coluna), r"[^\d\.]", ""))
    # Regra C: Converter para decimal (18,2)
    df_fin = df_fin.withColumn(coluna, col(coluna).cast(DecimalType(18,2)))
    # Regra D: Garantir que valores zerados ou negativos sejam nulos
    df_fin = df_fin.withColumn(coluna, 
        when(col(coluna) <= 0, None)
        .otherwise(col(coluna))
    )

# 4. Calcular valores em Reais (BRL) usando a cotação isolada no passo 1
df_fin = df_fin.withColumn("orcamento_brl", round(col("orcamento_usd") * lit(taxa_dolar), 2).cast(DecimalType(18,2))) \
               .withColumn("receita_brl", round(col("receita_usd") * lit(taxa_dolar), 2).cast(DecimalType(18,2)))

# 5. Derivar Lucro e Margem de Lucro (MANTIDO INTACTO!)
df_fin = df_fin.withColumn("lucro_usd", (col("receita_usd") - col("orcamento_usd")).cast(DecimalType(18,2))) \
               .withColumn("lucro_brl", (col("receita_brl") - col("orcamento_brl")).cast(DecimalType(18,2)))

df_fin = df_fin.withColumn("margem_lucro_percentual", 
    round((col("lucro_usd") / col("receita_usd")) * 100, 2).cast(DecimalType(18,2))
)

# 6. Deduplicação por Filme e Seleção das Colunas Finais (NOVO!)
window_fin = Window.partitionBy("id_filme").orderBy(col("ingestion_datetime").desc())
df_fin = df_fin.withColumn("num_linha", row_number().over(window_fin)) \
               .filter(col("num_linha") == 1) \
               .select(
                   "id_filme", "orcamento_usd", "receita_usd", 
                   "orcamento_brl", "receita_brl", 
                   "lucro_usd", "lucro_brl", "margem_lucro_percentual"
               )

# 7. Salvar na camada Silver sobrescrevendo o schema antigo
df_fin.write.format("delta") \
      .mode("overwrite") \
      .option("overwriteSchema", "true") \
      .saveAsTable("silver.tb_financeiro_filmes")

print(f"Tabela silver.tb_financeiro_filmes criada! Conversão BRL aplicada: R$ {taxa_dolar:.4f}")
display(df_fin)

Tabela silver.tb_financeiro_filmes criada! Conversão BRL aplicada: R$ 4.9853


id_filme,orcamento_usd,receita_usd,orcamento_brl,receita_brl,lucro_usd,lucro_brl,margem_lucro_percentual
1000004,null,null,null,null,null,null,null
1000005,null,null,null,null,null,null,null
1000007,null,null,null,null,null,null,null
1000011,null,null,null,null,null,null,null
1000014,null,null,null,null,null,null,null
1000030,null,null,null,null,null,null,null
1000054,null,null,null,null,null,null,null
1000058,4700000.00,null,23430910.00,null,null,null,null
1000059,null,null,null,null,null,null,null
1000073,6000000.00,null,29911800.00,null,null,null,null


In [0]:
from pyspark.sql.functions import col, when, regexp_replace, expr, trim, row_number
from pyspark.sql.window import Window

# 1. Ler os dados brutos da tabela de métricas
df_metrics = spark.read.table("bronze.tb_movies_metrics")

# 2. Renomear as colunas conforme o mapeamento exigido e padronizar id_filme
df_metrics = df_metrics.withColumnRenamed("id", "id_filme") \
                       .withColumnRenamed("popularity", "popularidade") \
                       .withColumnRenamed("vote_average", "nota_media_tmdb") \
                       .withColumnRenamed("vote_count", "qtd_votos_tmdb") \
                       .withColumnRenamed("averageRating", "nota_media_imdb") \
                       .withColumnRenamed("numVotes", "qtd_votos_imdb") \
                       .withColumn("id_filme", trim(col("id_filme").cast("string")))

# 3. Limpeza de formatação da coluna popularidade
df_metrics = df_metrics.withColumn("popularidade", regexp_replace(col("popularidade"), ",", "."))
df_metrics = df_metrics.withColumn("popularidade", regexp_replace(col("popularidade"), r"[^\d\.-]", ""))

# 4. Conversão de tipagem segura (Safe Cast) contra Column Shift
df_metrics = df_metrics.withColumn("popularidade", expr("try_cast(popularidade as double)")) \
                       .withColumn("nota_media_tmdb", expr("try_cast(nota_media_tmdb as double)")) \
                       .withColumn("nota_media_imdb", expr("try_cast(nota_media_imdb as double)")) \
                       .withColumn("qtd_votos_tmdb", expr("try_cast(qtd_votos_tmdb as int)")) \
                       .withColumn("qtd_votos_imdb", expr("try_cast(qtd_votos_imdb as int)"))

# 5. Tratamento de limites numéricos de negócio
for coluna_nota in ["nota_media_tmdb", "nota_media_imdb"]:
    df_metrics = df_metrics.withColumn(coluna_nota, 
        when((col(coluna_nota) < 0) | (col(coluna_nota) > 10), None)
        .otherwise(col(coluna_nota))
    )

for coluna_positiva in ["popularidade", "qtd_votos_tmdb", "qtd_votos_imdb"]:
    df_metrics = df_metrics.withColumn(coluna_positiva, 
        when(col(coluna_positiva) < 0, None)
        .otherwise(col(coluna_positiva))
    )

# 6. Deduplicação por Filme e Seleção das Colunas Finais (NOVO!)
window_met = Window.partitionBy("id_filme").orderBy(col("ingestion_datetime").desc())
df_metrics = df_metrics.withColumn("num_linha", row_number().over(window_met)) \
                       .filter(col("num_linha") == 1) \
                       .select(
                           "id_filme", "popularidade", "nota_media_tmdb", 
                           "qtd_votos_tmdb", "nota_media_imdb", "qtd_votos_imdb"
                       )

# 7. Salvar na camada Silver sobrescrevendo o schema antigo
df_metrics.write.format("delta") \
          .mode("overwrite") \
          .option("overwriteSchema", "true") \
          .saveAsTable("silver.tb_metricas_engajamento")

print("Tabela silver.tb_metricas_engajamento higienizada e criada com sucesso!")
display(df_metrics)

Tabela silver.tb_metricas_engajamento higienizada e criada com sucesso!


id_filme,popularidade,nota_media_tmdb,qtd_votos_tmdb,nota_media_imdb,qtd_votos_imdb
1000058,1.489,6.75,6,6.2,382
1000059,0.6,0.0,0,7.7,25
1000073,13.212,6.8,15,null,236
1000081,102.802,5.142,134,5.1,1841
1000092,4.797,null,null,null,130
1000094,2.645,6.9,28,6.5,null
1000096,0.71,10.0,1,6.3,695
1000099,0.6,0.0,0,8.6,33
1000108,3.231,0.0,0,6.5,157
1000110,1.38,0.0,0,6.9,263


In [0]:
from pyspark.sql.functions import col, when, trim, expr

# 1. Ler os dados da tabela de avaliações na camada Bronze
df_reviews = spark.read.table("bronze.tb_movies_reviews")

# 2. Renomear as colunas e padronizar id_filme
df_reviews = df_reviews.withColumnRenamed("id", "id_filme") \
                       .withColumnRenamed("nome", "nome_usuario") \
                       .withColumnRenamed("nota", "nota_usuario") \
                       .withColumnRenamed("comentario", "comentario_usuario") \
                       .withColumn("id_filme", trim(col("id_filme").cast("string")))

# 3. Aplicar a regra de negócio da nota (escala de 0 a 10 com conversão segura)
df_reviews = df_reviews.withColumn("nota_usuario", expr("try_cast(nota_usuario as double)"))
df_reviews = df_reviews.withColumn("nota_usuario", 
    when((col("nota_usuario") < 0) | (col("nota_usuario") > 10), None)
    .otherwise(col("nota_usuario"))
)

# 4. Tratar comentários não preenchidos ou apenas com espaços em branco
df_reviews = df_reviews.withColumn("comentario_usuario", 
    when(col("comentario_usuario").isNull() | (trim(col("comentario_usuario")) == ""), "Sem comentário")
    .otherwise(col("comentario_usuario"))
)

# 5. Selecionar apenas as 4 colunas finais e remover registros integralmente duplicados
df_reviews = df_reviews.select("id_filme", "nome_usuario", "nota_usuario", "comentario_usuario") \
                       .dropDuplicates(["id_filme", "nome_usuario", "nota_usuario", "comentario_usuario"])

# 6. Salvar na camada Silver sobrescrevendo o schema antigo
df_reviews.write.format("delta") \
          .mode("overwrite") \
          .option("overwriteSchema", "true") \
          .saveAsTable("silver.tb_avaliacoes_usuarios")

print("Tabela silver.tb_avaliacoes_usuarios criada e higienizada com sucesso!")
display(df_reviews)

Tabela silver.tb_avaliacoes_usuarios criada e higienizada com sucesso!


id_filme,nome_usuario,nota_usuario,comentario_usuario
442113,Mariana Cardoso 277,4.4,Sem comentário
637007,Lucas Reis 602,3.9,Sem comentário
449479,Sérgio Freitas,0.7,Péssimo em todos os sentidos.
413036,Gabriela Monteiro 401,7.5,Sem comentário
528480,Leonardo Monteiro,6.3,Assisti até o final mas não me marcou.
387727,Maria Alves 707,8.2,"Gostei bastante, recomendo."
1032506,Amanda Castro 242,4.7,"Fraco, não recomendo."
446554,Sandra Rodrigues 736,6.5,Assisti até o final mas não me marcou.
569916,Camila Lima 489,8.2,Muito bom! Vale a pena assistir.
864552,Roberto Almeida 555,9.3,"Obra-prima do cinema, simplesmente espetacular."


In [0]:
from pyspark.sql.functions import col, split, explode, trim, regexp_replace, length

# 1. Ler os dados da tabela que contém as tags e gêneros na camada Bronze
df_credits = spark.read.table("bronze.tb_credits_and_tags")

# Selecionar apenas o ID do filme (convertido para string) e a coluna de gêneros
df_generos = df_credits.select(
    trim(col("id").cast("string")).alias("id_filme"), 
    col("genres")
)

# 2. Tratar a inconsistência de separadores
df_generos = df_generos.withColumn("genres", regexp_replace(col("genres"), r"[;\|]", ","))

# 3. Desmembrar (Split) e Explodir (Explode) a coluna
df_generos = df_generos.withColumn("genero", explode(split(col("genres"), ",")))

# 4. Limpeza de resíduos e anomalias de Column Shift
df_generos = df_generos.withColumn("genero", trim(col("genero")))

df_generos = df_generos.filter(
    (col("genero") != "") & 
    (col("genero").isNotNull()) & 
    (~col("genero").rlike(r"\d")) & 
    (length(col("genero")) <= 30)
)

# 5. Remover a coluna original e garantir a unicidade
df_generos = df_generos.select("id_filme", "genero").dropDuplicates()

# 6. Salvar na camada Silver sobrescrevendo o schema antigo
df_generos.write.format("delta") \
          .mode("overwrite") \
          .option("overwriteSchema", "true") \
          .saveAsTable("silver.tb_generos")

print("Tabela silver.tb_generos criada, explodida e higienizada com sucesso!")
display(df_generos)

Tabela silver.tb_generos criada, explodida e higienizada com sucesso!


id_filme,genero
329865,Mystery
269149,Animation
429617,Science Fiction
330459,Action
127380,Family
332562,Romance
291805,Action
293167,Action
381284,History
454626,Action


In [0]:
from pyspark.sql.functions import col, lit, split, explode, trim, initcap, regexp_replace, length

# 1. Ler os dados originais
df_credits = spark.read.table("bronze.tb_credits_and_tags")

# Mapeamento das regras de negócio
mapeamento_entidades = {
    "cast": "Ator",
    "directors": "Diretor",
    "writers": "Roteirista",
    "production_companies": "Produtora"
}

dfs_entidades = []

# 2. Processar cada coluna individualmente
for coluna_origem, tipo_resultante in mapeamento_entidades.items():
    
    # Isolar o ID do filme (convertido para string) e a coluna da vez
    df_temp = df_credits.select(
        trim(col("id").cast("string")).alias("id_filme"),
        col(coluna_origem)
    )
    
    # Padronizar separadores caso existam sujeiras
    df_temp = df_temp.withColumn(coluna_origem, regexp_replace(col(coluna_origem), r"[;\|]", ","))
    
    # Desmembrar e explodir para gerar uma linha por pessoa/empresa
    df_temp = df_temp.withColumn("nome_entidade", explode(split(col(coluna_origem), ",")))
    
    # 3. Limpeza, Capitalização e Tipagem
    df_temp = df_temp.withColumn("nome_entidade", initcap(trim(col("nome_entidade")))) \
                     .withColumn("tipo_entidade", lit(tipo_resultante))
                     
    # Descartar linhas que ficaram vazias após o split
    df_temp = df_temp.filter(
    (col("nome_entidade") != "") & 
    (col("nome_entidade").isNotNull()) & 
    (~col("nome_entidade").rlike(r"^\d+$")) & 
    (length(col("nome_entidade")) <= 80)
    )
    
    # Selecionar apenas as colunas finais padronizadas
    df_temp = df_temp.select("id_filme", "nome_entidade", "tipo_entidade")
    
    # Guardar na lista para empilhar depois
    dfs_entidades.append(df_temp)

# 4. Consolidar os 4 DataFrames em um único modelo (Empilhamento)
df_pessoas_empresas = dfs_entidades[0].union(dfs_entidades[1]) \
                                      .union(dfs_entidades[2]) \
                                      .union(dfs_entidades[3])

# 5. Eliminar registros duplicados
df_pessoas_empresas = df_pessoas_empresas.dropDuplicates()

# 6. Salvar na camada Silver sobrescrevendo o schema antigo
df_pessoas_empresas.write.format("delta") \
                   .mode("overwrite") \
                   .option("overwriteSchema", "true") \
                   .saveAsTable("silver.tb_pessoas_empresas")

print("Tabela silver.tb_pessoas_empresas unificada e padronizada com sucesso!")
display(df_pessoas_empresas)

Tabela silver.tb_pessoas_empresas unificada e padronizada com sucesso!


id_filme,nome_entidade,tipo_entidade
299536,Don Cheadle,Ator
263115,Hugh Jackman,Ator
354912,Anthony Gonzalez,Ator
419430,Daniel Kaluuya,Ator
424694,Mike Myers,Ator
374720,Mark Rylance,Ator
321612,Ewan Mcgregor,Ator
335983,Tom Hardy,Ator
363088,Evangeline Lilly,Ator
363088,Randall Park,Ator


In [0]:
from pyspark.sql.functions import col, to_date, explode, sequence, last
from pyspark.sql.window import Window

# 1. Ler os dados da cotação na camada Bronze
df_cotacao = spark.read.table("bronze.tb_cotacao_dolar")

# Converter a dataHora para apenas Data (YYYY-MM-DD) e garantir que não há datas duplicadas
df_cotacao = df_cotacao.withColumn("data_original", to_date(col("dataHoraCotacao")))
df_cotacao = df_cotacao.dropDuplicates(["data_original"])

# 2. Descobrir a data inicial e final dinamicamente
min_date, max_date = df_cotacao.selectExpr("min(data_original)", "max(data_original)").first()

# 3. Gerar a Série Temporal Contínua
df_calendario = spark.sql(f"SELECT explode(sequence(to_date('{min_date}'), to_date('{max_date}'))) as data_referencia")

# 4. Fazer o Join com os dados reais
df_completo = df_calendario.join(df_cotacao, df_calendario.data_referencia == df_cotacao.data_original, "left")

# 5. Aplicar o Forward Fill (Preenchimento para frente)
janela = Window.orderBy("data_referencia").rowsBetween(Window.unboundedPreceding, 0)

df_silver_cotacao = df_completo.select(
    col("data_referencia"),
    last("cotacaoCompra", ignorenulls=True).over(janela).alias("cotacaoCompra")
)

# 6. Salvar na camada Silver sobrescrevendo o schema antigo
df_silver_cotacao.write.format("delta") \
                 .mode("overwrite") \
                 .option("overwriteSchema", "true") \
                 .saveAsTable("silver.tb_cotacao_dolar")

print("Tabela silver.tb_cotacao_dolar criada com série temporal contínua e Forward Fill com sucesso!")
display(df_silver_cotacao)

/databricks/python/lib/python3.12/site-packages/pyspark/sql/connect/expressions.py:1155: UserWarning: WARN WindowExpression: No Partition Defined for Window operation! Moving all data to a single partition, this can cause serious performance degradation.
  warnings.warn(


Tabela silver.tb_cotacao_dolar criada com série temporal contínua e Forward Fill com sucesso!


data_referencia,cotacaoCompra
2026-09-28,5.2126
2026-09-29,5.2198
2026-09-30,5.1803
2026-10-01,5.2073
2026-10-02,5.2232
2026-10-03,5.2232
2026-10-04,5.2232
2026-10-05,4.9853
